<a href="https://colab.research.google.com/github/marviiiin/Computer-Vision/blob/main/DL4CV_GenerativeModels.ipynb" target="_parent"><img src="https://colab.research.google.com/assets/colab-badge.svg" alt="Open In Colab"/></a>

In [ ]:
import keras
import torch
import numpy as np
from google.colab.patches import cv2_imshow

In [ ]:
class MNIST0(torch.utils.data.Dataset):
  def __init__(self):
    (x_train, y_train), _ = keras.datasets.mnist.load_data()
    self.x_train = ((x_train[y_train == 0]-127.5)/42.5).reshape(-1, 28*28).astype(np.float32)

  def __len__(self):
      return len(self.x_train)

  def __getitem__(self, idx):
    x = torch.from_numpy(self.x_train[idx])
    z = torch.randn_like(x)
    t = torch.rand(1)
    xt = (1-t)*x + t*z
    return xt, t, z-x

train_dataset = MNIST0()
train_dataloader = torch.utils.data.DataLoader(train_dataset, batch_size=64, shuffle=True)

In [ ]:
for xt, t, v in train_dataloader:
  print(xt.size(), xt.min(), xt.max(), t.size())

  for i in range(5):
    print(t[i])
    img = (xt[i].numpy().reshape(28,28)*40.0+127.0).astype(np.uint8).copy()
    cv2_imshow(img)

  break

torch.Size([64, 784]) tensor(-4.1359) tensor(3.7922) torch.Size([64, 1])
tensor([0.8409])


tensor([0.7139])


tensor([0.6590])


tensor([0.0353])


tensor([0.4334])


In [ ]:
class Net(torch.nn.Module):
    def __init__(self):
        super().__init__()
        self.fc1 = torch.nn.Linear(784+1, 512)
        self.fc2 = torch.nn.Linear(512, 256)
        self.fc3 = torch.nn.Linear(256, 512)
        self.fc4 = torch.nn.Linear(512, 784)

    def forward(self, xt, t):
        x = torch.cat((xt, t), dim=1)
        x = torch.nn.functional.relu(self.fc1(x))
        x = torch.nn.functional.relu(self.fc2(x))
        x = torch.nn.functional.relu(self.fc3(x))
        x = self.fc4(x)
        return x

model = Net().cuda()

optimizer = torch.optim.Adam(model.parameters(), lr=0.001)

for i in range(100):
  model.train()
  lsum = 0
  for xt, t, v in train_dataloader:
    optimizer.zero_grad()

    pred_v = model(xt.cuda(), t.cuda())
    loss = torch.mean(torch.sum(torch.square(v.cuda()-pred_v), dim=1))
    loss.backward()
    optimizer.step()

    lsum += loss.item()*len(xt)
  lsum /= len(train_dataset)

  model.eval()
  print(i, lsum)
  z = torch.randn((1,784)).cuda()
  for t in torch.linspace(1,0,50):
    #print(z.size(), t.size())
    with torch.no_grad():
      pred_v = model(z, t.view(1,1).cuda())
    #print(pred_v.size())
    z = z - pred_v/50
    #print(z.size())

    img = (np.clip(z[0].cpu().numpy(), -3, 3).reshape(28,28)*40.0+127.0).astype(np.uint8).copy()
    cv2_imshow(img)


0 2918.5225426337215


1 2007.6388073621238


2 1810.3532208673419


3 1674.59632077234


4 1598.2479589340878


...

95 1242.8677215756506


96 1241.823967870055


97 1241.8451425866986


98 1246.08597478266


99 1230.3621590398723
